In [1]:
%load_ext autoreload
%autoreload 2

In [2]:
import os

import torch
import torch.nn as nn
import torch.optim as optim
import torch.nn.functional as F

import pickle

from torch import Tensor
from torch.utils.data import DataLoader

from torchvision.datasets import MNIST
from torchvision.transforms import ToTensor
from torchvision import transforms, datasets

import pytorch_lightning as pl

from tqdm.notebook import tqdm
from argparse import Namespace
from skimage.transform import resize
import matplotlib.pyplot as plt

from rietools_pt import *

from utils import one_hot_decode, one_hot_encode

In [3]:
def parse_fasta(file_path):
    with open(file_path, 'r') as file:
        sequences = {}
        current_sequence = ""
        current_header = ""
        
        for line in file:
            line = line.rstrip()  # Remove newline character
            
            if line.startswith(">"):
                if current_header:
                    # Save the previous sequence if one exists
                    sequences[current_header] = current_sequence
                
                # Start a new sequence
                current_header = line[1:]  # Remove the ">" character
                current_sequence = ""
            else:
                # Continue the current sequence
                current_sequence += line
        
        if current_header:
            # Save the last sequence in the file
            sequences[current_header] = current_sequence
        
        return sequences


In [4]:
d_c19_protein = parse_fasta('data/sequences_protein_eu_c19.fasta')

In [5]:
d_c19_protein_ = {}
for k,v in d_c19_protein.items():
    d_c19_protein_[k] = (v, one_hot_encode(v))

In [7]:
for k,v in d_c19_protein_.items():
    print(k, v[1].shape)

WAQ35188.1 |ORF1ab polyprotein [Severe acute respiratory syndrome coronavirus 2] (7096, 24)
WAQ35189.1 |ORF1a polyprotein [Severe acute respiratory syndrome coronavirus 2] (4405, 24)
WAQ35190.1 |surface glycoprotein [Severe acute respiratory syndrome coronavirus 2] (1273, 24)
WAQ35191.1 |ORF3a protein [Severe acute respiratory syndrome coronavirus 2] (275, 24)
WAQ35192.1 |envelope protein [Severe acute respiratory syndrome coronavirus 2] (75, 24)
WAQ35193.1 |membrane glycoprotein [Severe acute respiratory syndrome coronavirus 2] (222, 24)
WAQ35194.1 |ORF6 protein [Severe acute respiratory syndrome coronavirus 2] (61, 24)
WAQ35195.1 |ORF7a protein [Severe acute respiratory syndrome coronavirus 2] (121, 24)
WAQ35196.1 |ORF7b [Severe acute respiratory syndrome coronavirus 2] (43, 24)
WAQ35197.1 |ORF8 protein [Severe acute respiratory syndrome coronavirus 2] (119, 24)
WAQ35198.1 |nucleocapsid phosphoprotein [Severe acute respiratory syndrome coronavirus 2] (419, 24)
WAQ35199.1 |ORF10 prote